In [21]:
import numpy as np
import pandas as pd

from pathlib import Path

from collections import defaultdict
from typing import DefaultDict, List, Dict

import plotly.express as px
import plotly.graph_objects as go
from plotly.subplots import make_subplots

In [6]:
DATA_DIR = Path("../data/raw")
FILE_PATH = DATA_DIR / "fraudTest.csv"

dtf = pd.read_csv(FILE_PATH,index_col=0)

In [7]:
print(f'data frame shape : {dtf.shape}')

data frame shape : (555719, 22)


In [16]:
dtf.head(3)

,trans_date_trans_time,cc_num,merchant,category,amt,first,last,gender,street,city,...,lat,long,city_pop,job,dob,trans_num,unix_time,merch_lat,merch_long,is_fraud
0,2020-06-21 12:14:25,2291163933867244,fraud_Kirlin and Sons,personal_care,2.86,Jeff,Elliott,M,351 Darlene Green,Columbia,...,33.9659,-80.9355,333497,Mechanical engineer,1968-03-19,2da90c7d74bd46a0caf3777415b3ebd3,1371816865,33.986391,-81.200714,0
1,2020-06-21 12:14:33,3573030041201292,fraud_Sporer-Keebler,personal_care,29.84,Joanne,Williams,F,3638 Marsh Union,Altonah,...,40.3207,-110.4360,302,"Sales professional, IT",1990-01-17,324cc204407e99f51b0d6ca0055005e7,1371816873,39.450498,-109.960431,0
2,2020-06-21 12:14:53,3598215285024754,"fraud_Swaniawski, Nitzsche and Welch",health_fitness,41.28,Ashley,Lopez,F,9333 Valentine Point,Bellmore,...,40.6729,-73.5365,34496,"Librarian, public",1970-10-21,c81755dbbbea9d5c77f094348a7579be,1371816893,40.495810,-74.196111,0


### columns data types ###

In [20]:
dtf.dtypes


trans_date_trans_time        str
cc_num                     int64
merchant                     str
category                     str
amt                      float64
first                        str
last                         str
gender                       str
street                       str
city                         str
state                        str
zip                        int64
lat                      float64
long                     float64
city_pop                   int64
job                          str
dob                          str
trans_num                    str
unix_time                  int64
merch_lat                float64
merch_long               float64
is_fraud                   int64
dtype: object

## classify column categories ###

In [18]:
id_metadata_col_list = ['cc_num','trans_num','first','last','street']
feature_candidate_col_list = ['merchant','category', 'amt', 'gender','city','state','zip','lat','long', 'city_pop','job','dob','merch_lat','merch_long']
temporal_col_list = ['trans_date_trans_time','unix_time']
target_col = 'is_fraud'

categorical_col_list = ["merchant","category", "gender", "city","state","job"]
numeric_col_list = ['amt','lat','long','city_pop','merch_lat','merch_long','unix_time']


## Vérifier ce que renvoie l'api de prédiction temps réel ##

In [106]:
import requests

API_URL = "https://sdacelo-real-time-fraud-detection.hf.space/current-transactions"
response = requests.get(API_URL)

response.raise_for_status()

data = response.json()
data

'{"columns":["cc_num","merchant","category","amt","first","last","gender","street","city","state","zip","lat","long","city_pop","job","dob","trans_num","merch_lat","merch_long","is_fraud","current_time"],"index":[258142],"data":[[30270432095985,"fraud_Skiles LLC","home",258.37,"Lisa","Lin","F","908 Brooks Brook","Lomax","IL",61454,40.6761,-91.0391,725,"Environmental consultant","1972-11-28","4ba994c6450954b7d35f207be0646e44",39.748629,-90.81943,1,1790862883776]]}'

In [104]:
dtf.loc[107739]

trans_date_trans_time                 2020-07-28 13:38:01
cc_num                                    180081032825079
merchant                          fraud_Powlowski-Weimann
category                                      food_dining
amt                                                 43.87
first                                              Connie
last                                              Carroll
gender                                                  F
street                         872 Justin Views Suite 746
city                                               Duncan
state                                                  MS
zip                                                 38740
lat                                                34.047
long                                             -90.7652
city_pop                                              466
job                             Trading standards officer
dob                                            1955-04-03
trans_num     

In [105]:
dtf[dtf["trans_num"] == "12024c51b7f8f75070876ae123c626e1"]

,trans_date_trans_time,cc_num,merchant,category,amt,first,last,gender,street,city,...,long,city_pop,job,dob,trans_num,unix_time,merch_lat,merch_long,is_fraud,amt_bin
107739,2020-07-28 13:38:01,180081032825079,fraud_Powlowski-Weimann,food_dining,43.87,Connie,Carroll,F,872 Justin Views Suite 746,Duncan,...,-90.7652,466,Trading standards officer,1955-04-03,12024c51b7f8f75070876ae123c626e1,1375018681,33.917106,-89.850616,0,25-50


### First eda summary ###

In [19]:
eda_summary = pd.DataFrame({
    "dtype": dtf.dtypes,
    "n_unique": dtf.nunique(),
    "missing": dtf.isna().sum(),
    "missing_pct": dtf.isna().mean() * 100
})

eda_summary

,dtype,n_unique,missing,missing_pct
trans_date_trans_time,str,544760,0,0.0
cc_num,int64,924,0,0.0
merchant,str,693,0,0.0
category,str,14,0,0.0
amt,float64,37256,0,0.0
first,str,341,0,0.0
last,str,471,0,0.0
gender,str,2,0,0.0
street,str,924,0,0.0
city,str,849,0,0.0


**Data Set seems to have a structure composed of cc_num (credit cart number) along with its related attributes like street, gps coords with at least one person by credit card. These clients have executed all payments / transactions toward a approx 693 merchants**

In [10]:
def get_columns_by_dtype(dataset:pd.DataFrame) -> DefaultDict[str,List[str]]:
    columns_by_dtype = defaultdict(list)
    for col, dtype in dataset.dtypes.to_dict().items():
        columns_by_dtype[str(dtype)].append(col)
    return columns_by_dtype

In [ ]:
dtf.describe()

,cc_num,amt,zip,lat,long,city_pop,unix_time,merch_lat,merch_long,is_fraud
count,5.557190e+05,555719.000000,555719.000000,555719.000000,555719.000000,5.557190e+05,5.557190e+05,555719.000000,555719.000000,555719.000000
mean,4.178387e+17,69.392810,48842.628015,38.543253,-90.231325,8.822189e+04,1.380679e+09,38.542798,-90.231380,0.003860
std,1.309837e+18,156.745941,26855.283328,5.061336,13.721780,3.003909e+05,5.201104e+06,5.095829,13.733071,0.062008
min,6.041621e+10,1.000000,1257.000000,20.027100,-165.672300,2.300000e+01,1.371817e+09,19.027422,-166.671575,0.000000
25%,1.800429e+14,9.630000,26292.000000,34.668900,-96.798000,7.410000e+02,1.376029e+09,34.755302,-96.905129,0.000000
50%,3.521417e+15,47.290000,48174.000000,39.371600,-87.476900,2.408000e+03,1.380762e+09,39.376593,-87.445204,0.000000
75%,4.635331e+15,83.010000,72011.000000,41.894800,-80.175200,1.968500e+04,1.385867e+09,41.954163,-80.264637,0.000000
max,4.992346e+18,22768.110000,99921.000000,65.689900,-67.950300,2.906700e+06,1.388534e+09,66.679297,-66.952026,1.000000


### Target Distribution ###

In [15]:
dtf["is_fraud"].value_counts(normalize=True)

is_fraud
0    0.99614
1    0.00386
Name: proportion, dtype: float64

**-> Unbalanced target**

### Numerical variables analysis ###

#### amt (payment amount) ####

In [25]:
dtf["amt"].describe()

count    555719.000000
mean         69.392810
std         156.745941
min           1.000000
25%           9.630000
50%          47.290000
75%          83.010000
max       22768.110000
Name: amt, dtype: float64

In [22]:
fig = px.histogram(
    dtf,
    x="amt",
    nbins=100,
    title="Distribution of transaction amounts"
)

fig.show()

In [24]:
fig = px.box(
    dtf,
    x="is_fraud",
    y="amt",
    points=False,
    title="Transaction amount by fraud status"
)

fig.show()

***amt distribution asymetric. Thus extrem amt values are collapsing visualisations***

#### Focus on amt distribution < q99 and focus on queue ####

In [35]:
q99 = dtf["amt"].quantile(0.99)

dtf["amt"].quantile([0.50, 0.75, 0.90, 0.95, 0.99, 0.995, 0.999])

0.500      47.2900
0.750      83.0100
0.900     135.5500
0.950     193.0510
0.990     519.8546
0.995     787.1646
0.999    1572.7235
Name: amt, dtype: float64

In [29]:
dtf_main = dtf[dtf["amt"] <= q99]
dtf_high = dtf[dtf["amt"] > q99]

print(f"Seuil 99e percentile : {q99:.2f}")
print(f"Transactions <= seuil : {len(dtf_main):,}")
print(f"Transactions > seuil : {len(dtf_high):,}")

Seuil 99e percentile : 519.85
Transactions <= seuil : 550,161
Transactions > seuil : 5,558


In [30]:
fig = px.histogram(
    dtf_main,
    x="amt",
    nbins=100,
    title="Distribution des montants — 99 % des transactions"
)

fig.show()

In [31]:
fig = px.histogram(
    dtf_high,
    x="amt",
    nbins=50,
    title="Distribution des montants — 1 % des transactions les plus élevées"
)

fig.show()

In [38]:
dtf["amt_bin"] = pd.cut(
    dtf["amt"],
    bins=[0, 10, 25, 50, 100, 250, 500, 1000, float("inf")],
    labels=["0-10", "10-25", "25-50", "50-100",
            "100-250", "250-500", "500-1000", "1000+"]
)

fraud_by_amt = (
    dtf.groupby("amt_bin", observed=True)["is_fraud"]
    .agg(
        transaction_count="count",
        fraud_count="sum",
        fraud_rate="mean"
    )
    .reset_index()
)

fraud_by_amt

,amt_bin,transaction_count,fraud_count,fraud_rate
0,0-10,144250,150,0.001040
1,10-25,54821,296,0.005399
2,25-50,89859,16,0.000178
3,50-100,166804,18,0.000108
4,100-250,84522,83,0.000982
5,250-500,9385,546,0.058178
6,500-1000,4495,760,0.169077
7,1000+,1583,276,0.174352


In [37]:
fig = px.bar(
    fraud_by_amt,
    x="amt_bin",
    y="fraud_rate",
    title="Taux de fraude selon le montant de la transaction",
    labels={
        "amt_bin": "Montant",
        "fraud_rate": "Taux de fraude"
    }
)

fig.show()

In [39]:
pd.crosstab(
    pd.cut(
        dtf["amt"],
        bins=[0, 10, 25, 50, 100, 250, 500, 1000, float("inf")]
    ),
    dtf["is_fraud"],
    normalize="index"
)

is_fraud,0,1
amt,,
"(0.0, 10.0]",0.998960,0.001040
"(10.0, 25.0]",0.994601,0.005399
"(25.0, 50.0]",0.999822,0.000178
"(50.0, 100.0]",0.999892,0.000108
"(100.0, 250.0]",0.999018,0.000982
"(250.0, 500.0]",0.941822,0.058178
"(500.0, 1000.0]",0.830923,0.169077
"(1000.0, inf]",0.825648,0.174352


In [41]:
px.histogram(
    dtf[dtf["is_fraud"] == 1],
    x="amt",
    nbins=100,
    title="Distribution des montants des transactions frauduleuses"
)

In [40]:
dtf.loc[dtf["is_fraud"] == 1, "amt"].describe()

count    2145.000000
mean      528.356494
std       392.747594
min         1.780000
25%       214.510000
50%       371.940000
75%       907.770000
max      1320.920000
Name: amt, dtype: float64

In [42]:
fig = px.bar(
    fraud_by_amt,
    x="amt_bin",
    y="fraud_rate",
    text_auto=".2%",
    title="Taux de fraude selon la tranche de montant",
    labels={
        "amt_bin": "Montant de la transaction",
        "fraud_rate": "Taux de fraude"
    }
)

fig.show()

#### Analyses amt X category ####

In [49]:
bins = [0, 10, 25, 50, 100, 250, 500, 1000, float("inf")]

labels = [
    "0-10",
    "10-25",
    "25-50",
    "50-100",
    "100-250",
    "250-500",
    "500-1000",
    "1000+"
]

category_amt = (
    dtf
    .assign(
        amt_bin=pd.cut(
            dtf["amt"],
            bins=bins,
            labels=labels
        )
    )
    .groupby(
        ["category", "amt_bin"],
        observed=True
    )["is_fraud"]
    .agg(
        transaction_count="count",
        fraud_count="sum",
        fraud_rate="mean"
    )
    .reset_index()
)
#category_amt

In [54]:
category_amt.shape
#category_amt.head()
category_amt["transaction_count"].sum()

np.int64(555719)

#### Top fraud_rate (transaction_count >= 100) ####

In [55]:
category_amt[
    category_amt["transaction_count"] >= 100
].sort_values(
    "fraud_rate",
    ascending=False
).head(20)

,category,amt_bin,transaction_count,fraud_count,fraud_rate
28,grocery_pos,250-500,574,482,0.839721
15,gas_transport,10-25,147,84,0.571429
80,shopping_net,1000+,609,232,0.380952
56,misc_net,500-1000,772,263,0.340674
79,shopping_net,500-1000,1107,274,0.247516
87,shopping_pos,500-1000,1061,173,0.163054
41,home,250-500,314,38,0.121019
90,travel,10-25,141,12,0.085106
88,shopping_pos,1000+,545,40,0.073394
19,grocery_net,0-10,201,14,0.069652


#### Top fraud_count ####

In [57]:
category_amt.sort_values(
    "fraud_count",
    ascending=False
).head(20)[
    [
        "category",
        "amt_bin",
        "transaction_count",
        "fraud_count",
        "fraud_rate"
    ]
]

,category,amt_bin,transaction_count,fraud_count,fraud_rate
28,grocery_pos,250-500,574,482,0.839721
79,shopping_net,500-1000,1107,274,0.247516
56,misc_net,500-1000,772,263,0.340674
80,shopping_net,1000+,609,232,0.380952
87,shopping_pos,500-1000,1061,173,0.163054
15,gas_transport,10-25,147,84,0.571429
14,gas_transport,0-10,70,70,1.000000
44,kids_pets,10-25,7773,64,0.008234
67,personal_care,10-25,7708,57,0.007395
11,food_dining,100-250,4779,51,0.010672


In [50]:
fraud_matrix = category_amt.pivot(
    index="category",
    columns="amt_bin",
    values="fraud_rate"
)
fraud_matrix.columns = fraud_matrix.columns.astype(str)

fig = px.imshow(
    fraud_matrix,
    text_auto=".2%",
    aspect="auto",
    title="Taux de fraude selon la catégorie et le montant",
    labels={
        "x": "Tranche de montant",
        "y": "Catégorie",
        "color": "Taux de fraude"
    }
)

fig.show()

In [58]:
fraud_count_matrix = category_amt.pivot(
    index="category",
    columns="amt_bin",
    values="fraud_count"
)

fig = px.imshow(
    fraud_count_matrix,
    text_auto=True,
    aspect="auto",
    title="Nombre de fraudes selon la catégorie et le montant",
    labels={
        "x": "Tranche de montant",
        "y": "Catégorie",
        "color": "Nombre de fraudes"
    }
)

fig.show()

#### city_pop variable analysis ####

In [88]:
population_stats = (
    dtf
    .assign(
        pop_bin=pd.cut(
            dtf["city_pop"],
            bins=[0, 10_000, 50_000, 100_000, 500_000, float("inf")]
        )
    )
    .groupby("pop_bin", observed=True)["is_fraud"]
    .agg(
        transaction_count="count",
        fraud_count="sum",
        fraud_rate="mean"
    )
    .reset_index()
)

population_stats 

,pop_bin,transaction_count,fraud_count,fraud_rate
0,"(0.0, 10000.0]",389959,1553,0.003982
1,"(10000.0, 50000.0]",62243,248,0.003984
2,"(50000.0, 100000.0]",27601,136,0.004927
3,"(100000.0, 500000.0]",47888,119,0.002485
4,"(500000.0, inf]",28028,89,0.003175


**No monotonic relation between city size and fraud_rate**

#### distance between purchaser and merchant variable analysis ####

In [89]:
# Aversine formula
import numpy as np

lat1 = np.radians(dtf["lat"])
lon1 = np.radians(dtf["long"])

lat2 = np.radians(dtf["merch_lat"])
lon2 = np.radians(dtf["merch_long"])

dlat = lat2 - lat1
dlon = lon2 - lon1

a = (
    np.sin(dlat / 2) ** 2
    + np.cos(lat1) * np.cos(lat2) * np.sin(dlon / 2) ** 2
)

distance_km = 2 * 6371 * np.arcsin(np.sqrt(a))

In [90]:
distance_km.describe()

count    555719.000000
mean         76.104902
std          29.117079
min           0.123883
25%          55.286255
50%          78.179517
75%          98.520760
max         150.922504
dtype: float64

In [92]:

distance_km.sort_values(ascending=False).head(10)

265756    150.922504
354324    148.791046
204763    148.395235
194983    148.237615
18285     148.210240
39402     148.028585
237533    147.948250
258440    147.736098
272255    147.715637
308357    147.712572
dtype: float64

In [93]:
bins = [0, 25, 50, 75, 100, 125, 150, float("inf")]
labels = [
    "0-25 km",
    "25-50 km",
    "50-75 km",
    "75-100 km",
    "100-125 km",
    "125-150 km",
    "150+ km"
]

In [95]:
distance_stats = (
    dtf
    .assign(
        distance_km=distance_km,
        distance_bin=pd.cut(
            distance_km,
            bins=bins,
            labels=labels
        )
    )
    .groupby("distance_bin", observed=True)["is_fraud"]
    .agg(
        transaction_count="count",
        fraud_count="sum",
        fraud_rate="mean"
    )
    .reset_index()
)

distance_stats

,distance_bin,transaction_count,fraud_count,fraud_rate
0,0-25 km,28256,108,0.003822
1,25-50 km,85467,327,0.003826
2,50-75 km,141986,547,0.003852
3,75-100 km,170181,668,0.003925
4,100-125 km,113043,430,0.003804
5,125-150 km,16785,65,0.003873
6,150+ km,1,0,0.000000


**La distance client-marchand ne présente pas de variation notable du taux de fraude selon les tranches de distance. Elle ne montre donc pas de signal univarié évident dans cet échantillon. Mais on peut conserver cette feature pour le modèle car il peut y avoir d'éventuelles interactions avec d'autres variables.**

#### trans_date_trans_time analysis ####

In [98]:
dtf_time = (
    dtf
    .assign(
        trans_datetime=pd.to_datetime(dtf["trans_date_trans_time"]),
        hour=lambda x: x["trans_datetime"].dt.hour,
        day_of_week=lambda x: x["trans_datetime"].dt.dayofweek
    )
)


In [99]:
hour_stats = (
    dtf_time
    .groupby("hour")["is_fraud"]
    .agg(
        transaction_count="count",
        fraud_count="sum",
        fraud_rate="mean"
    )
    .reset_index()
)

In [100]:
hour_stats

,hour,transaction_count,fraud_count,fraud_rate
0,0,18153,188,0.010356
1,1,18461,169,0.009154
2,2,18140,168,0.009261
3,3,18199,194,0.010660
4,4,18075,15,0.000830
5,5,17917,20,0.001116
6,6,18106,14,0.000773
7,7,18098,16,0.000884
8,8,17993,10,0.000556
9,9,18046,14,0.000776


In [101]:
day_of_week_stats = (
    dtf_time
    .groupby("day_of_week")["is_fraud"]
    .agg(
        transaction_count="count",
        fraud_count="sum",
        fraud_rate="mean"
    )
    .reset_index()
)

In [102]:
day_of_week_stats

,day_of_week,transaction_count,fraud_count,fraud_rate
0,0,115136,302,0.002623
1,1,110113,331,0.003006
2,2,52840,266,0.005034
3,3,59456,309,0.005197
4,4,62806,297,0.004729
5,5,62270,266,0.004272
6,6,93098,374,0.004017


**On peut voir que l'heure de transaction présente un signal fortement discriminant dans les données historiques, mais elle ne sera pas retenue pour l'entraînement du modèle car l'API de prédiction remplace trans_date_trans_time par current_time, qui ne représente pas l'heure réelle de la transaction.**

### Categorical variables analysis ###

#### Gender variable analysis ####

In [60]:
gender_stats = (
    dtf.groupby("gender")["is_fraud"]
    .agg(
        transaction_count="count",
        fraud_count="sum",
        fraud_rate="mean"
    )
    .reset_index()
)
gender_stats

,gender,transaction_count,fraud_count,fraud_rate
0,F,304886,1164,0.003818
1,M,250833,981,0.003911


In [61]:
contingency_table = pd.crosstab(
    dtf["gender"],
    dtf["is_fraud"]
)

contingency_table

is_fraud,0,1
gender,,
F,303722,1164
M,249852,981


In [62]:
from scipy.stats import chi2_contingency

chi2, p_value, dof, expected = chi2_contingency(
    contingency_table
)

print(f"Chi² = {chi2:.4f}")
print(f"p-value = {p_value:.4e}")

Chi² = 0.2868
p-value = 5.9228e-01


In [63]:
import numpy as np

n = contingency_table.to_numpy().sum()
r, k = contingency_table.shape

cramers_v = np.sqrt(
    chi2 / (n * min(r - 1, k - 1))
)

print(f"Cramér's V = {cramers_v:.6f}")

Cramér's V = 0.000718


gender ne présente pas d'association statistiquement détectable avec is_fraud dans cet échantillon (chi^2=0.287), \(p=0.592\). L'intensité de l'association est par ailleurs quasi nulle (V=0.000718\).

#### Merchant variable analysis ####

In [65]:
merchant_stats = (
    dtf.groupby("merchant")["is_fraud"]
    .agg(
        transaction_count="count",
        fraud_count="sum",
        fraud_rate="mean"
    )
    .reset_index()
)

merchant_stats[
    merchant_stats["transaction_count"] >= 100
].sort_values(
    "fraud_rate",
    ascending=False
).head(20)

,merchant,transaction_count,fraud_count,fraud_rate
528,"fraud_Romaguera, Cruickshank and Greenholt",828,18,0.021739
386,fraud_Lemke-Gutmann,837,18,0.021505
443,"fraud_Mosciski, Ziemann and Farrell",870,18,0.020690
238,"fraud_Heathcote, Yost and Kertzmann",830,17,0.020482
523,"fraud_Rodriguez, Yost and Jenkins",501,10,0.019960
421,fraud_Medhurst PLC,772,15,0.019430
27,fraud_Bashirian Group,790,15,0.018987
342,fraud_Kris-Weimann,528,10,0.018939
237,fraud_Heathcote LLC,802,15,0.018703
36,fraud_Bednar Group,540,10,0.018519


#### cc_num variable analysis ####

In [66]:
customer_stats = (
    dtf.groupby("cc_num")["is_fraud"]
    .agg(
        transaction_count="count",
        fraud_count="sum",
        fraud_rate="mean"
    )
    .reset_index()
)

In [70]:
customer_stats.sort_values(
    "transaction_count",
    ascending=False
).head(10)

,cc_num,transaction_count,fraud_count,fraud_rate
821,6538441737335434,1474,18,0.012212
684,4586810168620942,1466,0,0.000000
123,4745996322265,1462,0,0.000000
892,4587657402165341815,1458,0,0.000000
389,2242542703101233,1428,0,0.000000
171,30273037698427,1426,0,0.000000
338,372520049757633,1403,0,0.000000
170,30270432095985,1386,15,0.010823
652,4364010865167176,1375,0,0.000000
309,344709867813900,1358,0,0.000000


In [72]:
customer_stats[
    customer_stats["transaction_count"] >= 100
].sort_values(
    "fraud_rate",
    ascending=False
).head(10)

,cc_num,transaction_count,fraud_count,fraud_rate
901,4725837176265195730,242,16,0.066116
139,30011465039817,242,16,0.066116
64,676275912597,215,14,0.065116
54,675961917837,203,13,0.064039
75,4026222041577,220,14,0.063636
839,6597248210463122,240,15,0.062500
193,30510856607165,213,12,0.056338
23,570273151375,233,13,0.055794
804,6011975266774121,217,12,0.055300
471,3527063666782582,239,13,0.054393


#### transactions count by card distribution ####

In [73]:
card_stats = (
    dtf.groupby("cc_num")["is_fraud"]
    .agg(
        transaction_count="count",
        fraud_count="sum",
        fraud_rate="mean"
    )
    .reset_index()
)

In [83]:
card_stats[
    card_stats["transaction_count"] >= 100
]["fraud_rate"].describe()

count    908.000000
mean       0.004881
std        0.011634
min        0.000000
25%        0.000000
50%        0.000000
75%        0.000000
max        0.066116
Name: fraud_rate, dtype: float64

In [84]:
(card_stats["fraud_count"] > 0).sum()

np.int64(218)

In [85]:
card_stats["cc_num"].nunique()

924

In [86]:
card_stats[card_stats["fraud_count"] > 0]["fraud_count"].describe()

count    218.000000
mean       9.839450
std        3.225318
min        2.000000
25%        8.000000
50%       10.000000
75%       12.000000
max       19.000000
Name: fraud_count, dtype: float64

***la fraude est concentrée sur une partie des cartes 218 cartes sur 924 présentent au moins 2 fraudes observées***

In [76]:
card_stats[
    card_stats["transaction_count"] >= 100
].sort_values(
    "fraud_rate",
    ascending=False
).head(10)

,cc_num,transaction_count,fraud_count,fraud_rate
901,4725837176265195730,242,16,0.066116
139,30011465039817,242,16,0.066116
64,676275912597,215,14,0.065116
54,675961917837,203,13,0.064039
75,4026222041577,220,14,0.063636
839,6597248210463122,240,15,0.062500
193,30510856607165,213,12,0.056338
23,570273151375,233,13,0.055794
804,6011975266774121,217,12,0.055300
471,3527063666782582,239,13,0.054393


In [77]:
card_stats[
    card_stats["transaction_count"] >= 100
].sort_values(
    "fraud_count",
    ascending=False
).head(10)

,cc_num,transaction_count,fraud_count,fraud_rate
686,4599285557366057,503,19,0.037773
821,6538441737335434,1474,18,0.012212
139,30011465039817,242,16,0.066116
901,4725837176265195730,242,16,0.066116
564,3577794103155425,472,16,0.033898
258,213112402583773,1263,16,0.012668
170,30270432095985,1386,15,0.010823
922,4989847570577635369,464,15,0.032328
356,375974680629816,902,15,0.016630
731,4904681492230012,1289,15,0.011637


In [81]:
contingency_table = pd.crosstab(dtf["cc_num"], dtf["is_fraud"])
from scipy.stats import chi2_contingency

chi2, p_value, dof, expected = chi2_contingency(contingency_table)
print(f"Chi² = {chi2:.4f}")
print(f"p-value = {p_value:.4e}")

Chi² = 52632.8170
p-value = 0.0000e+00


In [82]:

n = contingency_table.to_numpy().sum()
r, k = contingency_table.shape

cramers_v = np.sqrt(
    chi2 / (n * min(r - 1, k - 1))
)

print(f"Cramér's V = {cramers_v:.6f}")

Cramér's V = 0.307752


**L'analyse de cc_num met en évidence une hétérogénéité significative du taux de fraude entre les cartes. Le test du χ² rejette l'hypothèse d'indépendance entre cc_num et is_fraud (χ² = 52 632,8 ; p < 0,001), avec une intensité d'association non négligeable mesurée par un V de Cramér de 0,308.**

**cc_num est une variable candidate pertinente pour dériver des features comportementales historiques as-of (pour éviter historical leakage)**